# First NMF source-separation experiment

This notebook analyzes `outputs/synthetic_mixture.wav`. The sitar and tabla recordings used to make it are separate performances, not aligned stems from one performance, so this is only a basic demonstration—not a real-world source-separation benchmark.

Non-negative matrix factorization (NMF) approximates a non-negative spectrogram as the product of two smaller non-negative matrices. One matrix contains frequency patterns (components); the other describes how active each pattern is over time. NMF finds patterns in the mixture, but by itself it does not know which pattern is sitar or tabla.

## Imports and project paths

We use only NumPy, SciPy, scikit-learn, and soundfile for the audio and factorization work. The project root is located by searching the current folder and its parents for `outputs/synthetic_mixture.wav`.

In [19]:
from pathlib import Path

import numpy as np
import soundfile as sf
from scipy import signal
from sklearn.decomposition import NMF

root_candidates = [Path.cwd(), *Path.cwd().parents]
PROJECT_ROOT = next(
    (
        candidate
        for candidate in root_candidates
        if (candidate / "outputs" / "synthetic_mixture.wav").is_file()
    ),
    None,
)

if PROJECT_ROOT is None:
    raise FileNotFoundError(
        "Could not find outputs/synthetic_mixture.wav. Run the mixture notebook first."
    )

mixture_path = PROJECT_ROOT / "outputs" / "synthetic_mixture.wav"
print(f"Mixture input: {mixture_path}")

Mixture input: d:\indian-instrument-separation\outputs\synthetic_mixture.wav


## Load and validate the mixture

The file is read as floating-point audio. If it has multiple channels, they are averaged to mono. We check that it has samples and finite values before continuing. To keep the demonstration's memory use modest, only the first 30 seconds are analyzed.

In [20]:
if not mixture_path.is_file():
    raise FileNotFoundError(f"Mixture file does not exist: {mixture_path}")

try:
    mixture_audio, sample_rate = sf.read(
        mixture_path,
        dtype="float32",
        always_2d=True,
    )
except Exception as error:
    raise RuntimeError(f"Could not read '{mixture_path}': {error}") from error

if mixture_audio.shape[0] == 0 or mixture_audio.shape[1] == 0:
    raise ValueError("The mixture file contains no audio samples or channels.")
if not np.isfinite(mixture_audio).all():
    raise ValueError("The mixture contains NaN or infinite values.")

mixture_mono = mixture_audio.mean(axis=1)
max_duration_seconds = 30
number_of_samples = min(len(mixture_mono), max_duration_seconds * sample_rate)
mixture_mono = mixture_mono[:number_of_samples]

print(f"Sample rate: {sample_rate} Hz")
print(f"Analyzed duration: {number_of_samples / sample_rate:.2f} seconds")
print(f"Analyzed samples: {number_of_samples}")

Sample rate: 44100 Hz
Analyzed duration: 30.00 seconds
Analyzed samples: 1323000


## Check the SciPy STFT and inverse STFT approach

SciPy's `signal.stft` and `signal.istft` can be paired for this small demonstration: they support the same window, segment length, overlap, FFT length, one-sided spectrum, boundary handling, and spectrum scaling. SciPy now documents these functions as legacy and recommends `ShortTimeFFT` for new applications, but this familiar pair is adequate for explaining the basic workflow. The short round-trip check below verifies that the chosen settings return the input's sample count and a finite signal before NMF is applied.

In [21]:
nperseg = 2048
noverlap = 1024
hop_length = nperseg - noverlap

if len(mixture_mono) < nperseg:
    raise ValueError(
        f"The input must contain at least {nperseg} samples for this STFT setting."
    )

frequencies, times, mixture_stft = signal.stft(
    mixture_mono,
    fs=sample_rate,
    window="hann",
    nperseg=nperseg,
    noverlap=noverlap,
    nfft=nperseg,
    return_onesided=True,
    boundary="zeros",
    padded=True,
    scaling="spectrum",
)

_, round_trip_audio = signal.istft(
    mixture_stft,
    fs=sample_rate,
    window="hann",
    nperseg=nperseg,
    noverlap=noverlap,
    nfft=nperseg,
    input_onesided=True,
    boundary=True,
    scaling="spectrum",
)

extra_samples = len(round_trip_audio) - len(mixture_mono)
if extra_samples < 0 or extra_samples >= hop_length:
    raise ValueError(
        f"Unexpected STFT round-trip length: input has {len(mixture_mono)} samples, "
        f"inverse STFT returned {len(round_trip_audio)}."
    )
round_trip_audio = round_trip_audio[: len(mixture_mono)]

if round_trip_audio.shape != mixture_mono.shape:
    raise ValueError(
        f"STFT round-trip length mismatch: expected {mixture_mono.shape}, "
        f"got {round_trip_audio.shape}."
    )
if not np.isfinite(round_trip_audio).all():
    raise ValueError("The inverse STFT returned NaN or infinite values.")

round_trip_error = np.sqrt(np.mean((mixture_mono - round_trip_audio) ** 2))
print(f"STFT shape (frequency bins, frames): {mixture_stft.shape}")
print(f"Round-trip root-mean-square error: {round_trip_error:.8f}")

STFT shape (frequency bins, frames): (1025, 1293)
Round-trip root-mean-square error: 0.00000001


## Factorize the magnitude spectrogram

NMF requires non-negative input, so we factorize the absolute magnitude of the complex STFT. Each row passed to scikit-learn represents one time frame; each column represents one frequency bin. Four components and a limited iteration count keep this first experiment small. The component count is a modelling choice, not a claim that the mixture contains four instruments.

In [22]:
magnitude = np.abs(mixture_stft).astype(np.float32)
if magnitude.ndim != 2 or not np.isfinite(magnitude).all():
    raise ValueError("The magnitude spectrogram must be a finite 2D array.")
if np.any(magnitude < 0):
    raise ValueError("NMF input must be non-negative.")

n_components = 4
nmf_model = NMF(
    n_components=n_components,
    init="nndsvda",
    solver="cd",
    beta_loss="frobenius",
    max_iter=100,
    tol=1e-3,
    random_state=0,
)
activations = nmf_model.fit_transform(magnitude.T)

if activations.shape != (magnitude.shape[1], n_components):
    raise ValueError(f"Unexpected NMF activation dimensions: {activations.shape}.")
if nmf_model.components_.shape != (n_components, magnitude.shape[0]):
    raise ValueError(f"Unexpected NMF component dimensions: {nmf_model.components_.shape}.")

component_magnitudes = np.stack(
    [
        np.outer(nmf_model.components_[index], activations[:, index])
        for index in range(n_components)
    ]
)

if component_magnitudes.shape != (n_components, *magnitude.shape):
    raise ValueError(
        f"Unexpected reconstructed component dimensions: {component_magnitudes.shape}."
    )
if not np.isfinite(component_magnitudes).all():
    raise ValueError("NMF returned NaN or infinite component values.")

reconstructed_magnitude = component_magnitudes.sum(axis=0)
if reconstructed_magnitude.shape != magnitude.shape:
    raise ValueError("NMF reconstruction dimensions do not match the input spectrogram.")

print(f"Input magnitude shape: {magnitude.shape}")
print(f"Activation matrix shape: {activations.shape}")
print(f"Component matrix shape: {nmf_model.components_.shape}")
print(f"Magnitude reconstruction error: {nmf_model.reconstruction_err_:.6f}")

Input magnitude shape: (1025, 1293)
Activation matrix shape: (1293, 4)
Component matrix shape: (4, 1025)
Magnitude reconstruction error: 0.733475


## Make anonymous illustrative component estimates

NMF has found frequency patterns, but has not identified their instruments. We use each component's share of the reconstructed magnitude as a soft mask on the original complex STFT. The inverse STFT uses the same settings as the forward transform. This produces anonymous, approximate component signals for inspection; reusing the mixture phase can cause artifacts, and these estimates must not be called sitar or tabla without a separate identification method. No estimate is written to disk.

In [23]:
magnitude_total = reconstructed_magnitude
denominator = np.maximum(magnitude_total, np.finfo(np.float32).eps)
magnitude_masks = component_magnitudes / denominator[None, :, :]
component_stfts = magnitude_masks * mixture_stft[None, :, :]

component_audio = []
for index in range(n_components):
    _, estimate = signal.istft(
        component_stfts[index],
        fs=sample_rate,
        window="hann",
        nperseg=nperseg,
        noverlap=noverlap,
        nfft=nperseg,
        input_onesided=True,
        boundary=True,
        scaling="spectrum",
    )

    extra_samples = len(estimate) - len(mixture_mono)
    if extra_samples < 0 or extra_samples >= hop_length:
        raise ValueError(
            f"Component {index + 1} has an unexpected length: "
            f"expected {len(mixture_mono)} samples, got {len(estimate)}."
        )
    estimate = estimate[: len(mixture_mono)]

    if estimate.shape != mixture_mono.shape:
        raise ValueError(
            f"Component {index + 1} has shape {estimate.shape}; "
            f"expected {mixture_mono.shape}."
        )
    if not np.isfinite(estimate).all():
        raise ValueError(f"Component {index + 1} contains NaN or infinite values.")
    component_audio.append(estimate)

component_audio = np.stack(component_audio)
if component_audio.shape != (n_components, len(mixture_mono)):
    raise ValueError(f"Unexpected component audio dimensions: {component_audio.shape}.")

print(f"Anonymous component audio shape: {component_audio.shape}")
print("Components are unlabeled; no sitar/tabla assignment has been made.")

Anonymous component audio shape: (4, 1323000)
Components are unlabeled; no sitar/tabla assignment has been made.


## Summarize the factorization

The dimensions and peak magnitude of each anonymous component give a small, text-only summary of the decomposition. These values do not establish which instrument a component represents.

In [24]:
for index in range(n_components):
    estimate = component_audio[index]
    print(
        f"Anonymous component {index + 1}: "
        f"spectrogram shape={component_magnitudes[index].shape}, "
        f"audio samples={len(estimate)}, "
        f"peak amplitude={np.max(np.abs(estimate)):.6f}"
    )

Anonymous component 1: spectrogram shape=(1025, 1293), audio samples=1323000, peak amplitude=0.230979
Anonymous component 2: spectrogram shape=(1025, 1293), audio samples=1323000, peak amplitude=0.356898
Anonymous component 3: spectrogram shape=(1025, 1293), audio samples=1323000, peak amplitude=0.327789
Anonymous component 4: spectrogram shape=(1025, 1293), audio samples=1323000, peak amplitude=0.254107


## What this baseline does not establish

The factorization is unsupervised: components can capture timbre, pitch ranges, or repeated patterns, and their ordering is arbitrary. No component is reliably identified as sitar or tabla here. To evaluate actual separation, we would need defensibly identified target/reference tracks and suitable audio-quality metrics. Because the current synthetic mixture combines separate performances, this experiment is only a learning demonstration.

In [25]:
from IPython.display import Audio, display

for index in range(len(component_audio)):
    print(f"Anonymous component {index + 1}")
    display(Audio(component_audio[index], rate=sample_rate))

Anonymous component 1


Anonymous component 2


Anonymous component 3


Anonymous component 4
